In [1]:
from cobos.tokens import ibm_token, group_instance2
from qiskit_ibm_runtime import QiskitRuntimeService
from qiskit_aer.noise import NoiseModel
from qiskit_aer import AerSimulator

device = "ibm_fez"

service = QiskitRuntimeService(channel="ibm_quantum", token=ibm_token, instance=group_instance2)
backend = service.backend(device)
noise_model = NoiseModel.from_backend(backend)

In [2]:
noise_model.noise_instructions

['cz', 'id', 'measure', 'reset', 'sx', 'x']

In [3]:
noise_model.to_dict()

{'errors': [{'type': 'qerror',
   'id': 'a03dc759729e467eb73e796a21c9ee27',
   'operations': ['cz'],
   'instructions': [[{'name': 'pauli', 'qubits': [0, 1], 'params': ['II']},
     {'name': 'id', 'qubits': [0]},
     {'name': 'kraus',
      'qubits': [1],
      'params': [array([[-0.99994407+0.j,  0.        +0.j],
              [ 0.        +0.j, -0.99971901+0.j]]),
       array([[-0.01057648+0.j,  0.        +0.j],
              [ 0.        +0.j,  0.01057886+0.j]]),
       array([[0.        +0.j, 0.02121276+0.j],
              [0.        +0.j, 0.        +0.j]])]}],
    [{'name': 'pauli', 'qubits': [0, 1], 'params': ['II']},
     {'name': 'z', 'qubits': [0]},
     {'name': 'kraus',
      'qubits': [1],
      'params': [array([[-0.99994407+0.j,  0.        +0.j],
              [ 0.        +0.j, -0.99971901+0.j]]),
       array([[-0.01057648+0.j,  0.        +0.j],
              [ 0.        +0.j,  0.01057886+0.j]]),
       array([[0.        +0.j, 0.02121276+0.j],
              [0.        +0

In [4]:
import numpy as np
from qiskit import QuantumCircuit, transpile
from qiskit.quantum_info import Kraus, SuperOp
from qiskit_aer import AerSimulator
from qiskit.visualization import plot_histogram

# Import from Qiskit Aer noise module
from qiskit_aer.noise import (NoiseModel, QuantumError, ReadoutError,
    pauli_error, depolarizing_error, thermal_relaxation_error)

# Create an empty noise model
noise_model = NoiseModel()

# Add depolarizing error to all single qubit u1, u2, u3 gates
error = depolarizing_error(0.05, 1)
noise_model.add_all_qubit_quantum_error(error, ['u1', 'u2', 'u3'])

# Print noise model info
print(noise_model)

NoiseModel:
  Basis gates: ['cx', 'id', 'rz', 'sx', 'u1', 'u2', 'u3']
  Instructions with noise: ['u2', 'u3', 'u1']
  All-qubits errors: ['u1', 'u2', 'u3']


In [5]:
noise_model.to_dict()

{'errors': [{'type': 'qerror',
   'id': '6e4feb742ca143a8a2ea5577d98152b2',
   'operations': ['u1'],
   'instructions': [[{'name': 'id', 'qubits': [0]}],
    [{'name': 'x', 'qubits': [0]}],
    [{'name': 'y', 'qubits': [0]}],
    [{'name': 'z', 'qubits': [0]}]],
   'probabilities': [0.9625, 0.0125, 0.0125, 0.0125]},
  {'type': 'qerror',
   'id': '6e4feb742ca143a8a2ea5577d98152b2',
   'operations': ['u2'],
   'instructions': [[{'name': 'id', 'qubits': [0]}],
    [{'name': 'x', 'qubits': [0]}],
    [{'name': 'y', 'qubits': [0]}],
    [{'name': 'z', 'qubits': [0]}]],
   'probabilities': [0.9625, 0.0125, 0.0125, 0.0125]},
  {'type': 'qerror',
   'id': '6e4feb742ca143a8a2ea5577d98152b2',
   'operations': ['u3'],
   'instructions': [[{'name': 'id', 'qubits': [0]}],
    [{'name': 'x', 'qubits': [0]}],
    [{'name': 'y', 'qubits': [0]}],
    [{'name': 'z', 'qubits': [0]}]],
   'probabilities': [0.9625, 0.0125, 0.0125, 0.0125]}]}

In [9]:
def get_erradj_number_of_trotter_layers(times, chain_length, J, h, lamb, eplg_absolute, trotter_order, max_layers=10000):
    times_matrix = np.repeat(times, max_layers).reshape(len(times), max_layers)
    layers_arr = np.arange(1, max_layers + 1)
    ham_norm = chain_length*(np.abs(J) + np.abs(h) + np.abs(lamb)) - (np.abs(h) + np.abs(lamb))
    error_trotter = ((2*chain_length-1)**9*(ham_norm)**3*times_matrix**3)/layers_arr**2
    error_hardware = 1 - ((1-eplg_absolute)**(chain_length-1))**(4*layers_arr)
    error_total = error_trotter + error_hardware
    return np.argmin(error_total, axis=1) + 1

get_erradj_number_of_trotter_layers(np.linspace(0, 8, 35), 16, 1, 0.05, 0.7, 7.40e-4, 2)

array([    1, 10000, 10000, 10000, 10000, 10000, 10000, 10000, 10000,
       10000, 10000, 10000, 10000, 10000, 10000, 10000, 10000, 10000,
       10000, 10000, 10000, 10000, 10000, 10000, 10000, 10000, 10000,
       10000, 10000, 10000, 10000, 10000, 10000, 10000, 10000])

In [19]:
def get_number_of_layers(times, epsilon, chain_length, J, h, lamb, trotter_order=2):
    ham_norm = chain_length*(np.abs(J) + np.abs(h) + np.abs(lamb)) - (np.abs(h) + np.abs(lamb))
    nlayers = ((ham_norm*times)**(1+1/trotter_order))/(epsilon**(1/trotter_order))
    return nlayers

get_number_of_layers(np.linspace(0, 8, 35), 1e-2, 16, 1, 0.05, 0.7, 2)

array([    0.        ,   162.3552605 ,   459.21002265,   843.6226802 ,
        1298.84208402,  1815.18699494,  2386.12527172,  3006.86150332,
        3673.68018119,  4383.59203355,  5134.12413296,  5923.18630008,
        6748.98144157,  7609.94281555,  8504.68863634,  9431.9883014 ,
       10390.73667213, 11379.93409471, 12398.67061152, 13446.11329613,
       14521.49595948, 15624.11068521, 16753.30079607, 17908.45495469,
       19089.00217375, 20294.40756275, 21524.16867728, 22777.8123653 ,
       24054.89202655, 25354.98521814, 26677.69155197, 28022.63083977,
       29389.44144954, 30777.7788433 , 32187.31427131])